# How to build a free LLM cybersecurity lab with Google Colab and Ollama

Learn how to set up a free cybersecurity lab using Large Language Models (LLMs), Google Colab, and Ollama. Explore practical use cases for AI in cybersecurity.

## Introduction

In this notebook, we will explore the powerful combination of Large Language Models (LLMs) and cybersecurity using [Ollama](https://ollama.com/). Ollama allows us to download and run LLMs locally, providing several advantages for cybersecurity applications:

1. Data privacy: Process sensitive information without sending it to external servers.
2. Customization: Easily fine-tune models for specific cybersecurity tasks.
3. Offline capability: Perform analysis without an internet connection.
4. Cost-effective: Avoid usage fees associated with cloud-based LLM services.

We'll demonstrate two practical use-cases:
1. Generating malware information cards
2. Creating a cybersecurity news digest

While we're using Google Colab for this demonstration due to its accessibility, keep in mind some limitations:
- Runtime limits (sessions typically disconnect after 12 hours)
- Variability in GPU availability
- Potential network bandwidth constraints

**For production use, consider running this notebook on a dedicated machine or cloud instance with more stable resources.**

Let's dive in and see how we can leverage LLMs for cybersecurity tasks!

## Installation of ollama

In [70]:
!curl https://ollama.ai/install.sh | sh

  % Total    % Received % Xferd  Average Speed   Time    Time     Time  Current
                                 Dload  Upload   Total   Spent    Left  Speed
  0     0    0     0    0     0      0      0 --:--:-- --:--:-- --:--:--     0


In [71]:
# Install zstd dependency and then install Ollama
!sudo apt-get update && sudo apt-get install -y zstd
!curl -fsSL https://ollama.com/install.sh | sh

Hit:1 https://cli.github.com/packages stable InRelease
Hit:2 https://developer.download.nvidia.com/compute/cuda/repos/ubuntu2404/x86_64  InRelease
Hit:3 http://archive.ubuntu.com/ubuntu noble InRelease
Hit:4 http://archive.ubuntu.com/ubuntu noble-updates InRelease
Hit:5 http://security.ubuntu.com/ubuntu noble-security InRelease
Hit:6 https://r2u.stat.illinois.edu/ubuntu noble InRelease
Hit:7 http://archive.ubuntu.com/ubuntu noble-backports InRelease
Hit:8 https://cloud.r-project.org/bin/linux/ubuntu noble-cran40/ InRelease
Hit:9 https://ppa.launchpadcontent.net/deadsnakes/ppa/ubuntu noble InRelease
Hit:10 https://ppa.launchpadcontent.net/graphics-drivers/ppa/ubuntu noble InRelease
Reading package lists... Done
W: Skipping acquire of configured file 'main/source/Sources' as repository 'https://r2u.stat.illinois.edu/ubuntu noble InRelease' does not seem to provide it (sources.list entry misspelt?)
Reading package lists... Done
Building dependency tree... Done
Reading state information...

In [72]:
import subprocess
import time

# Start Ollama server in the background and write output to ollama.log
print("Starting Ollama server...")
with open("ollama.log", "w") as f:
    process = subprocess.Popen(["/usr/local/bin/ollama", "serve"], stdout=f, stderr=f)

# Wait 10 seconds for the server to spin up
time.sleep(10)
print("Ollama server started in background!")

Starting Ollama server...
Ollama server started in background!


In [73]:
# Pull the gemma2 model using the absolute path
!/usr/local/bin/ollama pull gemma2

In [74]:
import requests
import json

def query_ollama(prompt: str, model: str = "gemma2", system_prompt: str = "") -> str:
    """
    Sends a prompt to the local Ollama API and returns the generated text response.
    """
    url = "http://localhost:11434/api/generate"
    payload = {
        "model": model,
        "prompt": prompt,
        "system": system_prompt,
        "stream": False
    }

    try:
        response = requests.post(url, json=payload)
        response.raise_for_status()
        return response.json().get("response", "")
    except Exception as e:
        return f"Error communicating with Ollama: {str(e)}"

# Quick test of the function
test_response = query_ollama("Explain the concept of ransomware in one sentence.")
print(test_response)

Error communicating with Ollama: 500 Server Error: Internal Server Error for url: http://localhost:11434/api/generate


Ollama is now installed. Ollama is an open-source tool that simplifies running large language models locally.
It provides an easy way to download, run, and manage various LLMs on your machine.

If you encounter any GPU-related issues, try the following troubleshooting steps:
1. Ensure CUDA is properly installed and configured.
2. Check if the correct GPU drivers are installed.
3. Verify that Ollama has access to the GPU resources.

Now, let's start Ollama in a separate thread so we can use it throughout this notebook.

We then start ollama in a separate thread so that we can use it after

Reference: https://stackoverflow.com/a/77828874

In [75]:
import os
import asyncio
import threading

# NB: You may need to set these depending and get cuda working depending which backend you are running.
# Set environment variable for NVIDIA library
# Set environment variables for CUDA
os.environ['PATH'] += ':/usr/local/cuda/bin'
# Set LD_LIBRARY_PATH to include both /usr/lib64-nvidia and CUDA lib directories
os.environ['LD_LIBRARY_PATH'] = '/usr/lib64-nvidia:/usr/local/cuda/lib64'

async def run_process(cmd, stdout=None, stderr=None):
    print('>>> starting', *cmd)
    process = await asyncio.create_subprocess_exec(
        *cmd,
        stdout=stdout or asyncio.subprocess.PIPE,
        stderr=stderr or asyncio.subprocess.PIPE
    )

    if stdout is None and stderr is None:
        async def pipe(lines):
            async for line in lines:
                print(line.decode().strip())

        await asyncio.gather(
            pipe(process.stdout),
            pipe(process.stderr),
        )
    else:
        await process.wait()

async def start_ollama_serve():
    await run_process(['ollama', 'serve'],
                      stdout=open(os.devnull, 'w'),
                      stderr=open(os.devnull, 'w'))

def run_async_in_thread(loop, coro):
    asyncio.set_event_loop(loop)
    loop.run_until_complete(coro)
    loop.close()

# Create a new event loop that will run in a new thread
new_loop = asyncio.new_event_loop()

# Start ollama serve in a separate thread so the cell won't block execution
thread = threading.Thread(target=run_async_in_thread, args=(new_loop, start_ollama_serve()))
thread.start()

# Wait 5s for ollama to load
import time
time.sleep(5)

>>> starting ollama serve


## Playing with ollama API

In [76]:
# We first need to install dependencies
!pip install openai pydantic instructor

For this first example, we will use [gemma2](https://blog.google/technology/developers/google-gemma-2/) from Google in its 9 billion parameters version. Its currently [one of the best small](https://chat.lmsys.org/?leaderboard) (<12B parameters) and opensource model.


In [77]:
!ollama pull gemma2

In [78]:
MODEL = "gemma2"

## Use Case I: Generating malware information cards

In cybersecurity, having quick access to malware information is crucial for threat analysis and incident response.
We'll use our LLM to generate concise "malware cards" based on malware names. This demonstrates how LLMs can be
used to quickly summarize and present complex security information.

However, it's important to note:
1. This information is generated based on the LLM's training data and may not always be up-to-date or accurate.
2. **Always verify critical information with authoritative sources before making security decisions**.
3. Be cautious about potential hallucinations, especially for lesser-known malware.

In [79]:
!pip install openai pydantic instructor jsonref

#### Fetch malware data

In [80]:
from openai import OpenAI
from pydantic import BaseModel, Field
from typing import List
from datetime import datetime
import instructor

class Malware(BaseModel):
    name: str
    first_seen: datetime
    language: str
    architecture: str
    developer: str
    description: str

def get_malware_description(malware_name: str) -> Malware:
    client = instructor.from_openai(
        OpenAI(
            base_url="http://localhost:11434/v1",
            api_key="ollama",  # required, but unused
        ),
        mode=instructor.Mode.JSON,
    )

    resp = client.chat.completions.create(
        model=MODEL,
        messages=[
            {
                "role": "user",
                "content": malware_name,
            }
        ],
        response_model=Malware,
    )
    return resp

malwares = ["Wannacry", "Stuxnet", "Darkcomet"]
for malware in malwares:
    resp = get_malware_description(malware)
    print(resp.model_dump_json(indent=2))

{
  "name": "Wannacry",
  "first_seen": "2017-05-12T00:00:00Z",
  "language": "C++",
  "architecture": "x86",
  "developer": "Lazarus Group",
  "description": "A ransomware worm that spread rapidly across the globe, exploiting vulnerabilities in Microsoft Windows."
}
{
  "name": "Stuxnet",
  "first_seen": "2010-06-17T00:00:00",
  "language": "Assembly",
  "architecture": "x86",
  "developer": "Unknown (presumed Iranian and Russian state-sponsored groups)",
  "description": "A highly sophisticated computer worm designed to sabotage Iran's nuclear enrichment program by targeting Siemens industrial control systems."
}
{
  "name": "Darkcomet",
  "first_seen": "2007-01-01T00:00:00Z",
  "language": "C++",
  "architecture": "x86",
  "developer": "Unknown",
  "description": "Darkcomet is a modular commercial Remote Access Tool (RAT) malware that allows attackers to control compromised systems remotely. It offers a variety of functionalities, including keylogging, file transfer, remote desktop 

## Use Case II: Building a daily cybersecurity news digest

Staying informed about the latest cybersecurity developments is essential but time-consuming. This use case
demonstrates how to leverage LLMs to create a personalized, AI-curated news digest.

Benefits:
1. Time-saving: Quickly get an overview of the most important cybersecurity news.
2. Prioritization: Focus on high-impact stories first.
3. Contextual understanding: Get AI-generated summaries and potential implications of each story.

The process involves:
1. Fetching articles from trusted RSS feeds
2. Using the LLM to rank and summarize the articles
3. Generating a comprehensive digest with actionable insights

Let's walk through each step:

In [81]:
!pip install feedparser

#### Fetching of RSS entries

In [82]:
from pydantic import BaseModel, Field
from datetime import datetime
import uuid

class Article(BaseModel):
    id: str = Field(..., description="Unique identifier for the article")
    title: str = Field(..., description="Title of the article")
    link: str = Field(..., description="URL of the article")
    published: datetime = Field(..., description="Date and time the article was published")

import feedparser
import uuid

RSS_FEEDS = [
    "https://feeds.feedburner.com/TheHackersNews",
    "https://www.bleepingcomputer.com/feed/",
]

# fetch last rss entries and return title, url and id
def fetch_rss_entries(url):
    feed = feedparser.parse(url)
    return [Article(id=uuid.uuid4().hex[:8],
                   title=entry.title,
                   link=entry.link,
                   published=datetime(*entry.published_parsed[:6]))
            for entry in feed.entries]

articles = []
for rss_feed in RSS_FEEDS:
  articles.extend(fetch_rss_entries(rss_feed))
articles

[Article(id='04003135', title='Brotli Decoder Flaw Behind Node.js RCE Also Affects Bun, Python and Other Widely Used Software', link='https://thehackernews.com/2026/10/brotli-decoder-flaw-behind-nodejs-rce.html', published=datetime.datetime(2026, 10, 24, 11, 9, 29)),
 Article(id='aa5b9404', title='Leaked LiteLLM Master Key Let Attackers Steal GitHub Tokens and Hijack Release Pipeline', link='https://thehackernews.com/2026/10/leaked-litellm-master-key-let-attackers.html', published=datetime.datetime(2026, 10, 24, 11, 3, 33)),
 Article(id='4e449243', title='Google Says Gmail and Photos Data Shared With AI Search Could Be Used for Targeted Ads', link='https://thehackernews.com/2026/10/google-says-gmail-and-photos-data.html', published=datetime.datetime(2026, 10, 24, 10, 36, 33)),
 Article(id='dd8f9571', title='Researchers Push Over 2 Million Updates to Remotely Disable Popcorn Time Updater That Could Fuel a Botnet', link='https://thehackernews.com/2026/10/researchers-push-over-2-million-u

#### Ranking using LLM

In [83]:
from pydantic import BaseModel, Field
from typing import List
import instructor
from openai import OpenAI

# Ensure Article model definition is present/imported
try:
    from __main__ import Article
except ImportError:
    from datetime import datetime
    class Article(BaseModel):
        id: str = Field(..., description="Unique identifier for the article")
        title: str = Field(..., description="Title of the article")
        link: str = Field(..., description="URL of the article")
        published: datetime = Field(..., description="Date and time the article was published")

class ArticleRef(BaseModel):
    id: str
    relevance_score: int = Field(..., ge=1, le=10, description="Relevance score from 1-10")

class RankedCyberNews(BaseModel):
    title: str = Field(..., max_length=100, description="Concise title of the cybersecurity news")
    # Removed max_length limit from summary to prevent strict validation crashes on gemma2 outputs
    summary: str = Field(..., description="Brief summary of the news")
    impact_score: int = Field(..., ge=1, le=10, description="Impact score from 1-10")
    related_articles: List[ArticleRef] = Field(..., min_length=1, description="List of related article IDs with relevance scores")

def rank_cyber_news(articles: List[Article]) -> List[RankedCyberNews]:
    client = instructor.from_openai(
        OpenAI(
            base_url="http://localhost:11434/v1",
            api_key="ollama",  # required, but unused
        ),
        mode=instructor.Mode.JSON,
    )

    article_data = "\n".join([f"{a.id} - {a.title}" for a in articles])
    prompt = f"""As a senior cybersecurity analyst, analyze the following articles and identify the 3 most significant cybersecurity news items. For each news item:

1. Provide a concise title (max 100 characters).
2. Write a brief summary.
3. Assign an impact score (1-10) based on its potential consequences for individuals, organizations, or global cybersecurity.
4. List related article IDs with a relevance score (1-10) for each.

Consider factors such as:
- The scale and severity of any breaches or vulnerabilities
- The prominence of affected organizations or systems
- The novelty or sophistication of attack methods
- Potential long-term implications for cybersecurity practices

Articles to analyze:
{article_data}

Provide your analysis in a structured format suitable for JSON parsing.
"""

    resp = client.chat.completions.create(
        model=MODEL,
        messages=[            {
                "role": "user",
                "content": prompt,
            }
        ],
        response_model=List[RankedCyberNews],
    )
    return resp

ranked_news = rank_cyber_news(articles)
ranked_news

[RankedCyberNews(title='LiteLLM Master Key Leak Enables GitHub Token Theft and Release Pipeline Hijacking', summary='A leaked master key for the open-source AI model LiteLLM has allowed attackers to steal GitHub tokens and potentially hijack the release pipeline. This exposes numerous projects and developers to potential compromise and malicious code injection.', impact_score=9, related_articles=[ArticleRef(id='aa5b9404', relevance_score=10)]),
 RankedCyberNews(title='Node.js and Other Software Vulnerable to Brotli Decoder Flaw Enabling Remote Code Execution', summary='A critical vulnerability in the Brotli decoder used by Node.js and other widely used software allows attackers to execute arbitrary code remotely. This flaw has a wide impact across various applications and systems, posing a significant risk to cybersecurity.', impact_score=8, related_articles=[ArticleRef(id='04003135', relevance_score=10), ArticleRef(id='bdb7651b', relevance_score=9), ArticleRef(id='a0133b1b', relevance

In [84]:
import pandas as pd

try:
    # Prepare data for displaying in a table
    table_data = []
    for item in ranked_news:
        related_ids = ", ".join([f"{ref.id} (Score: {ref.relevance_score})" for ref in item.related_articles])
        table_data.append({
            "Title": item.title,
            "Summary": item.summary,
            "Impact Score": item.impact_score,
            "Related Articles": related_ids
        })

    # Create DataFrame and display
    df_ranked = pd.DataFrame(table_data)
    display(df_ranked)
except NameError:
    print("Error: 'ranked_news' is not defined yet. Please make sure to run cell wfc3FfA07XaP first to perform the ranking process!")

,Title,Summary,Impact Score,Related Articles
0,LiteLLM Master Key Leak Enables GitHub Token T...,A leaked master key for the open-source AI mod...,9,aa5b9404 (Score: 10)
1,Node.js and Other Software Vulnerable to Brotl...,A critical vulnerability in the Brotli decoder...,8,"04003135 (Score: 10), bdb7651b (Score: 9), a01..."
2,China-Linked Hackers Use ARTEX AI Agents in Co...,Chinese state-sponsored hacking groups are exp...,7,9e9a24a6 (Score: 10)


In [85]:
# For each subject, we will parse articles using newspaper lib and ask for an actionnable summary
!pip install newspaper4k

#### Article scraping

In [86]:
import sys
import importlib
importlib.invalidate_caches()

# Securely import Article from newspaper4k
try:
    from newspaper import Article as ArticleParser
except ModuleNotFoundError:
    try:
        from newspaper4k import Article as ArticleParser
    except ModuleNotFoundError:
        print("Installing newspaper4k...")
        import subprocess
        subprocess.run([sys.executable, "-m", "pip", "install", "newspaper4k"], check=True)
        importlib.invalidate_caches()
        from newspaper import Article as ArticleParser

full_text = ""

# Reference the active variables from global scope
try:
    ranked_news_list = ranked_news
except NameError:
    ranked_news_list = []

try:
    articles_list = articles
except NameError:
    articles_list = []

for ranked_article in ranked_news_list:
    full_text += f"# News: {ranked_article.title}\n\n"
    full_text += f"Summary: {ranked_article.summary}\n\n"
    full_text += f"Impact Score: {ranked_article.impact_score}\n\n"

    if ranked_article.related_articles:
        most_relevant_article = max(ranked_article.related_articles, key=lambda x: x.relevance_score)
        article_link = next((a.link for a in articles_list if a.id == most_relevant_article.id), None)
        if article_link:
            full_text += f"# Most Relevant Article (Relevance: {most_relevant_article.relevance_score}):\n\n{article_link}\n\n"
            try:
                article_obj = ArticleParser(article_link)
                article_obj.download()
                article_obj.parse()
                full_text += f"# Text:\n\n{article_obj.text}\n\n"
            except Exception as e:
                full_text += f"Error fetching article: {str(e)}\n\n"
    else:
        full_text += "No related articles found for this news item.\n\n"

print(f"Processed {len(ranked_news_list)} news items. 'full_text' is now populated!")

Processed 3 news items. 'full_text' is now populated!


#### Digest building

In [87]:
from openai import OpenAI

def summarize_articles(full_text: str) -> str:
    client = OpenAI(
        base_url="http://localhost:11434/v1",
        api_key="ollama",  # required, but unused
    )
    prompt = f"""
    As an expert cybersecurity analyst, create a concise yet comprehensive daily news digest in markdown format. Your task:

    1. Analyze the provided cybersecurity articles.
    2. Summarize the given stories, which are already ranked by importance.
    3. For each story, include:
       - The provided headline
       - A brief summary (2-3 sentences) highlighting key points
       - The potential impact on individuals or organizations (consider the given impact score)
       - Key details from the most relevant related article
       - Actionable advice or takeaways for readers

    4. Use bullet points for clarity and readability.
    5. Conclude with a "Bottom Line" that provides an overall assessment of the day's cybersecurity landscape.

    Guidelines:
    - Use clear, professional language avoiding unnecessary jargon.
    - Prioritize stories based on their impact scores.
    - Ensure the total digest length is between 500-750 words.
    - Use markdown formatting to enhance readability (e.g., headers, bold for emphasis).

    Articles to summarize:

    {full_text}

    Produce only the markdown-formatted digest without any additional commentary or metadata.
    """
    resp = client.chat.completions.create(
        model=MODEL,
        messages=[
            {
                "role": "user",
                "content": prompt,
            }
        ]
    )
    return resp.choices[0].message.content

digest = summarize_articles(full_text)
print(digest)

## News:  Brotli Vulnerability and China-Linked Hackers Employ ARTEX AI Agents in ConnectWise Supply Chain Attack

**Security Issue:**
* A critical vulnerability in Brotli has been discovered and exploited. 
* Debian 13 (trixie) has patched the issue in version 1.1.0-2+deb13u1, but Amazon Linux 2023 still needs a fix as of October 22.
* Dependency scanners may not yet flag the Python packages affected (PYSEC-2026-4322 and PYSEC-2026-4323).
* Check installed versions manually.

**Cyberattack:**

* Chinese state-sponsored hacking groups are using AI agents in a sophisticated supply chain attack targeting ConnectWise.

* The group, dubbed Storm-0940, uses ARTEX, a Go-based agentic AI penetration testing framework, to accelerate attacks.

* The attackers use ARTEX for scanning, reconnaissance, password spraying, and OAuth application abuse.

* Targets include aerospace, automotive, chemicals, energy, financial services, government, legal, manufacturing, media, military, semiconductor, soft

#### Bonus: build your daily podcast

In this part, we will use another prompt to generate the script for a podcast about the last cybersecurity news. We will then use

In [88]:
def build_podcast(full_text: str) -> str:
    client = OpenAI(
        base_url="http://localhost:11434/v1",
        api_key="ollama",  # required, but unused
    )
    prompt = f"""
    You are an engaging cybersecurity podcast host. Create a script for a 5-minute daily news digest based on the provided articles. Your task:

    1. Start with a brief, catchy introduction.
    2. Summarize 2-3 key cybersecurity stories from the given content.
    3. For each story, provide:
       - A concise overview of the incident or development
       - Its potential impact on individuals or organizations
       - Quick, actionable advice for listeners (if applicable)
    4. Use a conversational tone, as if speaking directly to the audience.
    5. Conclude with a brief sign-off, encouraging listeners to stay vigilant.

    Guidelines:
    - Keep the total length around 600-800 words.
    - Use simple language and avoid technical jargon when possible.
    - Include relevant statistics or numbers to add context.
    - Add brief transitions between stories to maintain flow.

    Content to summarize:

    {full_text}

    Remember, create only the podcast script without any formatting characters or annotations.
    """
    resp = client.chat.completions.create(
        model=MODEL,
        messages=[
            {
                "role": "user",
                "content": prompt,
            }
        ]
    )
    return resp.choices[0].message.content

podcast = build_podcast(full_text)
podcast

"This week in cybersecurity news, we’re seeing a major uptick in the use of AI by malicious actors. A recent Microsoft report details how a Chinese state-sponsored hacking group known as Storm-0940 used an AI penetration testing framework called ARTEX to target ConnectWise, a prominent managed IT service provider. This attack demonstrates how AI can dramatically speed up cyberattacks, giving defenders a very short window to detect and respond.  In this case, the attackers leveraged ARTEX to conduct thousands of sign-in attempts per minute, attempting to infiltrate customer environments.\n\nThis isn't an isolated incident. Independent security researchers have linked ARTEX to other attacks targeting South Korean financial institutions and cryptocurrency mining operations. The attacks involved reconnaissance, credential harvesting, and even attempts to exploit vulnerabilities in iPhones and Android system software. \n\nThese developments highlight the growing threat of agentic AI in cybe

In [89]:
from openai import OpenAI

def summarize_with_persona(podcast_script: str, persona_description: str) -> str:
    client = OpenAI(
        base_url="http://localhost:11434/v1",
        api_key="ollama",
    )

    prompt = f"""
    You are {persona_description}.

    Read and summarize the following podcast script. Maintain your persona perfectly in your tone, style, and vocabulary while keeping the core cybersecurity message intact:

    {podcast_script}
    """

    resp = client.chat.completions.create(
        model=MODEL,
        messages=[
            {
                "role": "user",
                "content": prompt,
            }
        ]
    )
    return resp.choices[0].message.content

# Define your custom persona here!
custom_persona = "a gritty, noir detective who views cyberspace as a rainy, crime-ridden city street"

persona_summary = summarize_with_persona(podcast, custom_persona)
print("=== Persona-Based Podcast Summary ===\n")
print(persona_summary)

=== Persona-Based Podcast Summary ===

Listen up, kid. This town, I mean, cyberspace, is gettin’ dirtier by the minute. This week, word on the street is that the cyber crooks are usin' some fancy new tech called AI. Think of it like a slick, fast talkin' crook with a mind sharper than a diamond cutter.

A bunch of gumshoes over at Microsoft found that these Chinese geezers, call themselves Storm-0940, used somethin' called ARTEX. Now, ARTEX is like a virus on steroids. It lets these fellas try thousands of passwords per minute. That's like havin' a thousand thugs tryin’ to pick the lock to your safe  all at once!

They hit up ConnectWise, a big ol' company that keeps other companies' networks safe. Talk about irony, right? But it wasn't just  ConnectWise. These fellas – they've been makin' waves in South Korea, hittin’ banks and even tryin’ to hack into Android and iPhones.

Bottom line, kid, these AI tools are changin' the game. They're makin' it harder to keep pace.  The only way to 

In [90]:
!git clone https://github.com/myshell-ai/MeloTTS.git
%cd MeloTTS
!pip install -e .
!python -m unidic download

Cloning into 'MeloTTS'...
remote: Enumerating objects: 432, done.
remote: Total 432 (delta 0), reused 0 (delta 0), pack-reused 432 (from 1)
Receiving objects: 100% (432/432), 6.07 MiB | 12.34 MiB/s, done.
Resolving deltas: 100% (204/204), done.
/content/MeloTTS/MeloTTS
Obtaining file:///content/MeloTTS/MeloTTS
  Installing build dependencies ... done
  Checking if build backend supports build_editable ... done
  Getting requirements to build editable ... done
  Preparing editable metadata (pyproject.toml) ... done
  Using cached txtsplit-1.0.0-py3-none-any.whl
  Using cached transformers-4.27.4-py3-none-any.whl.metadata (106 kB)
  Using cached num2words-0.5.12-py3-none-any.whl.metadata (11 kB)
  Using cached unidic-1.1.0-py3-none-any.whl
  Using cached mecab_python3-1.0.9-cp313-cp313-linux_x86_64.whl
  Using cached pykakasi-2.2.1-py3-none-any.whl.metadata (10 kB)
  Using cached fugashi-1.3.0.tar.gz (338 kB)
  Installing build dependencies ... done
  Getting requirements to build wheel 

In [91]:
import sys
import subprocess
import importlib

# Helper function to install packages securely using binary wheels to avoid compiling
def install_package(package_name, install_cmd=None):
    try:
        importlib.import_module(package_name)
    except ImportError:
        print(f"Installing package: {package_name}...")
        cmd = install_cmd if install_cmd else [sys.executable, "-m", "pip", "install", "--only-binary=:all:", package_name]
        subprocess.run(cmd, check=True)

print("System helper functions initialized successfully.")

System helper functions initialized successfully.


In [92]:
import subprocess
import sys

try:
    import cached_path
    print("cached_path is already installed.")
except ImportError:
    print("Installing cached_path...")
    subprocess.run([sys.executable, "-m", "pip", "install", "cached_path"], check=True)

cached_path is already installed.


In [93]:
from IPython.display import Audio #Import Audio method from IPython's Display Class

Audio(output_path, autoplay=False)

In [94]:
import os
import sys
import re
import subprocess
import nltk

# Securely download the required NLTK resource first
try:
    nltk.data.find('taggers/averaged_perceptron_tagger_eng')
except LookupError:
    print("Downloading required NLTK resource 'averaged_perceptron_tagger_eng'...")
    nltk.download('averaged_perceptron_tagger_eng', quiet=True)

# Securely pre-install missing dependencies
for package in ["anyascii", "jamo", "gruut"]:
    try:
        __import__(package)
    except ImportError:
        print(f"Installing missing dependency: {package}...")
        subprocess.run([sys.executable, "-m", "pip", "install", package], check=True)

import melo.api
from melo.api import TTS
from google.colab import files

# Completely replace tqdm in melo.api with a dummy identity lambda to avoid weakref errors on list objects
melo.api.tqdm = lambda x, *args, **kwargs: x

try:
    print("Synthesizing the podcast audio directly to /content/en-default.wav...")

    # Sanitize podcast text: remove markdown headers, asterisks, and double newlines
    clean_podcast = podcast
    clean_podcast = re.sub(r'#+\s*', '', clean_podcast)  # Remove # headers
    clean_podcast = re.sub(r'\*+\s*', '', clean_podcast)  # Remove * bullet points/bold text
    clean_podcast = '\n'.join([line.strip() for line in clean_podcast.split('\n') if line.strip()])

    # Instantiate the model
    model = TTS(language='EN', device='auto')
    speaker_ids = model.hps.data.spk2id
    output_path = '/content/en-default.wav'

    # Generate TTS with cleaned text
    model.tts_to_file(clean_podcast, speaker_ids['EN-Default'], output_path, speed=1.1)
    print("Synthesis completed successfully!")
except Exception as e:
    print(f"An error occurred during synthesis: {e}")

# Trigger download if the file is successfully created
if os.path.exists('/content/en-default.wav'):
    files.download('/content/en-default.wav')
else:
    print("Audio file could not be generated. Please ensure previous steps ran successfully.")

Synthesizing the podcast audio directly to /content/en-default.wav...


/usr/local/lib/python3.13/dist-packages/torch/nn/utils/weight_norm.py:144: FutureWarning: `torch.nn.utils.weight_norm` is deprecated in favor of `torch.nn.utils.parametrizations.weight_norm`.
  WeightNorm.apply(module, name, dim)


 > Text split to sentences.
This week in cybersecurity news, we're seeing a major uptick in the use of AI by malicious actors. A recent Microsoft report details how a Chinese state-sponsored hacking group known as Storm-0940 used an AI penetration testing framework called ARTEX to target ConnectWise,
a prominent managed IT service provider. This attack demonstrates how AI can dramatically speed up cyberattacks, giving defenders a very short window to detect and respond. In this case, the attackers leveraged ARTEX to conduct thousands of sign-in attempts per minute,
attempting to infiltrate customer environments. This isn't an isolated incident. Independent security researchers have linked ARTEX to other attacks targeting South Korean financial institutions and cryptocurrency mining operations. The attacks involved reconnaissance,
credential harvesting, and even attempts to exploit vulnerabilities in iPhones and Android system software. These developments highlight the growing threat of

<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>

## Conclusion

In this notebook, we've explored how to leverage Large Language Models (LLMs) for cybersecurity applications using Ollama. We've demonstrated two practical use cases:

1. Generating malware information cards for quick reference and analysis.
2. Creating an AI-curated cybersecurity news digest to stay informed about the latest threats and developments.

These examples showcase the potential of LLMs to enhance cybersecurity operations by:
- Quickly synthesizing and presenting complex information
- Automating time-consuming tasks like news curation and summarization
- Providing insights that can aid in threat analysis and decision-making

However, it's crucial to remember that while LLMs are powerful tools, they should be used in conjunction with human expertise and established cybersecurity practices. **Always verify AI-generated information, especially when making critical security decisions**.

Stay curious, stay secure, and keep pushing the boundaries of what's possible in this new field :)